# 08 — Discogs-EffNet (the cosine.club approach), against our own heard space

Hacker News research on cosine.club: cosine similarity between
embeddings from Essentia's Discogs-EffNet model (a style-classification
network repurposed for similarity — the classifier head is thrown away, the
1280-dim layer before it is kept) inside an approximate-nearest-neighbour
index. Three parts, and this notebook reproduces the first two at fma-small
scale to see how the resulting space compares to our own `heard` space:

1. **A pretrained model trained on a different task** — style classification
   on Discogs' catalogue. `modeling/essentia_embed.py` extracts its 1280-dim
   embedding layer for a track.
2. **Nearest-neighbour search over the embeddings** — brute-force cosine here
   (a few thousand tracks doesn't need FAISS; the *comparison* is the point,
   not building an index at cosine.club's scale).
3. **Cosine similarity as the score** — same as cosine.club, same as our own
   `TrackRecommender`.

Runs on a separate Python 3.11 environment (`.venv-essentia/`) because
`essentia-tensorflow` has no 3.13 wheel yet — this notebook's own kernel is
"Python 3.11 (essentia)", not the project's usual one, and deliberately does
**not** import anything from `modeling/` except `essentia_embed` itself, since
the rest of `modeling/` pulls in scikit-learn, librosa and mlflow, none of
which are installed here. Everything it needs from the heard-space side was
exported ahead of time to `data/processed/essentia_handoff/`.

Model: `discogs-effnet-bs64-1.pb`, CC BY-NC-SA 4.0 (non-commercial — fine for a
capstone, confirmed from Essentia's own model docs).

In [1]:
import sys
sys.path.append("..")

from pathlib import Path
import numpy as np
import pandas as pd
from IPython.display import Audio, display

from modeling.essentia_embed import embed_file, audio_path as fma_audio_path

REPO_ROOT = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
HANDOFF = REPO_ROOT / "data" / "processed" / "essentia_handoff"
pd.set_option("display.max_colwidth", 60)

## Embeddings

Extracted once by `modeling/essentia_embed.py` for the 2,001-track sample
(~250/genre, plus the seeds already used in notebooks 06-07) and cached to
`data/effnet_embeddings.npz` — re-running this cell just loads it back.

In [2]:
EMB_PATH = REPO_ROOT / "data" / "effnet_embeddings.npz"
loaded = np.load(EMB_PATH)
ids, E = loaded["ids"], loaded["embeddings"]
Eu = E / np.linalg.norm(E, axis=1, keepdims=True)

meta = pd.read_csv(HANDOFF / "sample_tracks.csv", index_col=0)
meta = meta.loc[ids]
pos = {int(t): i for i, t in enumerate(ids)}
print(f"{len(ids)} tracks embedded, {E.shape[1]} dims")

2001 tracks embedded, 1280 dims


In [3]:
def top_n(seed_id, n=10, exclude_same_artist=True):
    i = pos[seed_id]
    sims = Eu @ Eu[i]
    order = np.argsort(-sims)
    seed_artist = meta.loc[seed_id, "artist"]
    out = []
    for j in order:
        tid = int(ids[j])
        if tid == seed_id:
            continue
        if exclude_same_artist and meta.loc[tid, "artist"] == seed_artist:
            continue
        out.append((tid, 1 - sims[j]))
        if len(out) == n:
            break
    return out


def genre_names(track_id):
    return meta.loc[track_id, "genres_all"]


PREVIEW_SECONDS = 20
TARGET_RMS = 0.08
MAX_GAIN = 4.0


def load_preview(path, seconds=PREVIEW_SECONDS):
    import essentia.standard as es
    audio = es.MonoLoader(filename=str(path), sampleRate=22050)()
    sr = 22050
    skip = min(10.0, 0.1 * len(audio) / sr)
    start = int(skip * sr)
    end = min(start + int(seconds * sr), len(audio))
    start = max(0, end - int(seconds * sr))
    clip = audio[start:end]
    rms = float(np.sqrt(np.mean(clip ** 2))) or 1e-9
    gain = min(TARGET_RMS / rms, MAX_GAIN)
    return np.clip(clip * gain, -1.0, 1.0), sr


def play(path, label_text):
    # OGG/Vorbis, not raw Audio(clip, rate=sr): the uncompressed-WAV version
    # of this notebook hit 116MB and was unrenderable in some editors.
    import tempfile
    import os
    import soundfile as sf

    print(label_text)
    clip, sr = load_preview(path)
    with tempfile.NamedTemporaryFile(suffix=".ogg", delete=False) as f:
        sf.write(f.name, clip, sr, format="OGG", subtype="VORBIS")
        tmp_path = f.name
    try:
        display(Audio(filename=tmp_path))
    finally:
        os.unlink(tmp_path)

## 1. The same control seeds as notebook 06/07

Track 2 (AWOL — Food, Hip-Hop — acoustically coherent in heard space) and
track 3538 (Cryptacize — Say You Will, Pop — the incoherent one). Same seeds,
different embedding, so any difference is attributable to the model, not the
choice of track.

In [4]:
for seed_id in [2, 3538]:
    m = meta.loc[seed_id]
    print(f"\nSEED {seed_id}  {m.artist} — {m.title}  [{m.genre_top}]  genres_all={m.genres_all}")
    for tid, d in top_n(seed_id):
        mm = meta.loc[tid]
        print(f"  {d:.3f}  {mm.artist} — {mm.title}  [{mm.genre_top}]  genres_all={mm.genres_all}")


SEED 2  AWOL — Food  [Hip-Hop]  genres_all=[21]
  0.183  Majik Most — Deranged Barber  [Hip-Hop]  genres_all=[21]
  0.194  Alaclair Ensemble — Fa' faire du loot  [Hip-Hop]  genres_all=[811, 21]
  0.210  Sun Sunych ft. Sunniq & Alex East Block — I'd better (ft. Sunniq & Alex East Block)  [Hip-Hop]  genres_all=[539, 21]
  0.219  The Impossebulls — The GetBack  [Hip-Hop]  genres_all=[21]
  0.226  Hi-Rez — I Don't Fuck Witcha Ft. Young Scolla (Prod. Joel Johnston)  [Hip-Hop]  genres_all=[539, 21]
  0.230  Hi-Rez — Relax (Prod. Joel Johnston)  [Hip-Hop]  genres_all=[539, 21]
  0.231  The Impossebulls — 5 x 5  [Hip-Hop]  genres_all=[21]
  0.241  Food For Animals — Planet Say (featuring Faust)  [Hip-Hop]  genres_all=[21]
  0.242  9th Scientist — I Love Hip Hop  [Hip-Hop]  genres_all=[21]
  0.244  The Impossebulls — Blaque Gloves  [Hip-Hop]  genres_all=[21]

SEED 3538  Cryptacize — Say You Will  [Pop]  genres_all=[10, 76]
  0.165  Nalle — Ravens  [Folk]  genres_all=[17]
  0.178  Big Blood — A

**Listen:** both, EffNet's top-10.

In [5]:
for seed_id in [2, 3538]:
    m = meta.loc[seed_id]
    print(f"\n=== SEED {seed_id}  {m.artist} — {m.title} ===")
    play(fma_audio_path(seed_id), "SEED")
    for tid, d in top_n(seed_id):
        mm = meta.loc[tid]
        play(fma_audio_path(tid), f"distance={d:.3f}  {mm.artist} — {mm.title}  [{mm.genre_top}]")


=== SEED 2  AWOL — Food ===
SEED


distance=0.183  Majik Most — Deranged Barber  [Hip-Hop]


distance=0.194  Alaclair Ensemble — Fa' faire du loot  [Hip-Hop]


distance=0.210  Sun Sunych ft. Sunniq & Alex East Block — I'd better (ft. Sunniq & Alex East Block)  [Hip-Hop]


distance=0.219  The Impossebulls — The GetBack  [Hip-Hop]


...

distance=0.219  Damian Taveira & Juan Angel Italiano — Letromaquia O  [Experimental]


distance=0.224  Howie Mitchell — Deep Blue Sea (with Jean Ritchie)  [Folk]


distance=0.228  Rachel Ries — Adrian  [Folk]


distance=0.228  The Chapin Sisters — Bird Song  [Folk]


distance=0.229  Stephen Bartolomei — Weary Blues  [Folk]


## 2. Genre agreement@10, same method as notebook 06's sweep

Directly comparable to heard space's table: 30 seeds/genre (or all of them,
whichever is smaller, since this sample only has ~250/genre against heard
space's full 1000-4000/genre).

In [6]:
rng = np.random.default_rng(1)
rows = []
for genre in sorted(meta["genre_top"].dropna().unique()):
    pool = meta.index[meta["genre_top"] == genre].to_numpy()
    if len(pool) < 5:
        continue
    sample = rng.choice(pool, size=min(30, len(pool)), replace=False)
    for seed_id in sample:
        recs = top_n(int(seed_id), n=10)
        agree = np.mean([meta.loc[tid, "genre_top"] == genre for tid, _ in recs])
        rows.append({"genre": genre, "agreement@10": agree})

effnet_summary = pd.DataFrame(rows).groupby("genre")["agreement@10"].mean().round(3).sort_values()
effnet_summary

genre
Pop              0.170
Experimental     0.357
Instrumental     0.377
Folk             0.457
Rock             0.567
International    0.607
Electronic       0.613
Hip-Hop          0.753
Name: agreement@10, dtype: float64

## 3. Does "further" mean "adventurous" or just "different genre"?

A style-classification model's embedding space is, almost by definition,
organised around style. The open question was whether moving outward in it
buys real within-genre variety (genuinely adventurous) or just exits the genre
almost immediately (not adventurous, just *different*).

Test: for a batch of seeds, measure genre-agreement not just at rank 1-10 but
at rank ~100-110 and ~300-310 (a coarse version of the same geometric window
`depth_for()` already uses), and watch how fast it falls off.

In [7]:
def agreement_at_depth(seed_id, start, n=10):
    i = pos[seed_id]
    sims = Eu @ Eu[i]
    order = np.argsort(-sims)
    order = order[order != i]
    window = order[start:start + n]
    genre = meta.loc[seed_id, "genre_top"]
    return float(np.mean([meta.loc[int(ids[j]), "genre_top"] == genre for j in window]))


depth_rng = np.random.default_rng(2)
depth_rows = []
for genre in sorted(meta["genre_top"].dropna().unique()):
    pool = meta.index[meta["genre_top"] == genre].to_numpy()
    if len(pool) < 5:
        continue
    sample = depth_rng.choice(pool, size=min(20, len(pool)), replace=False)
    for seed_id in sample:
        for start, label in [(0, "rank 1-10"), (100, "rank 101-110"), (300, "rank 301-310")]:
            depth_rows.append({"genre": genre, "depth": label,
                                "agreement": agreement_at_depth(int(seed_id), start)})

depth_df = pd.DataFrame(depth_rows)
depth_df.groupby("depth")["agreement"].mean().round(3).reindex(["rank 1-10", "rank 101-110", "rank 301-310"])

depth
rank 1-10       0.526
rank 101-110    0.381
rank 301-310    0.224
Name: agreement, dtype: float64

**Answer, with numbers:** 0.526 -> 0.381 -> 0.224. Genre agreement more than
halves by rank 300, so "further away" in this space really does mean
"increasingly a different genre," not just "a more varied example of the same
genre" — your instinct about Bridge/Adventurous meaning genre-crossing was
right, at least for this embedding. But it's a slope, not a cliff: rank
101-110 still agrees 38% of the time, which is a real middle zone. That
middle distance is a reasonable place to look for Bridge tracks — audibly
related (still fairly close), often a different genre (agreement already
dropping) — before rank ~300+ becomes mostly genre-hopping rather than
discovery within a connected thread.

## 4. The external seed — does EffNet close the gap heard space couldn't?

Same seed, same 18 Spotify/YouTube recommendations, same percentile-rank
method as notebook 06 part 1. `heard_external_scoring.csv` carries heard
space's numbers for direct comparison.

Embedded ahead of time by the same standalone script, not live in this cell:
loading the Discogs-EffNet TensorFlow graph for the first time *inside a
running Jupyter kernel* reliably hung indefinitely here (confirmed: the exact
same code runs in seconds as a plain script — this looks like a known class of
TensorFlow/ipykernel event-loop conflict, not a problem with the model or the
audio). Every embedding in this notebook was computed by
`modeling/essentia_embed.py` run directly, never inside a kernel.

In [8]:
SEED_PATH = REPO_ROOT / "data" / "raw" / "youtube_tests" / "Y2Mate.is - Elyjah Slaps the Space.mp3"

external = np.load(HANDOFF / "external_effnet_embeddings.npz", allow_pickle=True)
ext_names, ext_platforms, ext_vecs = external["names"], external["platforms"], external["embeddings"]
ext_vecs_u = ext_vecs / np.linalg.norm(ext_vecs, axis=1, keepdims=True)

seed_row_idx = int(np.flatnonzero(ext_platforms == "seed")[0])
seed_vec_u = ext_vecs_u[seed_row_idx]

catalog_dist_sorted = np.sort(1 - (Eu @ seed_vec_u))
catalog_size = len(catalog_dist_sorted)


def catalog_rank(distance):
    return int(np.searchsorted(catalog_dist_sorted, distance)) + 1


rows = []
for i, (name, platform) in enumerate(zip(ext_names, ext_platforms)):
    if platform == "seed":
        continue
    d = float(1 - ext_vecs_u[i] @ seed_vec_u)
    rows.append({"platform": platform, "file": str(name),
                  "effnet_distance": d, "effnet_percentile": catalog_rank(d) / catalog_size})

effnet_scored = pd.DataFrame(rows)
heard_scored = pd.read_csv(HANDOFF / "heard_external_scoring.csv")
compare = effnet_scored.merge(heard_scored[["file", "heard_percentile"]], on="file")
compare[["platform", "file", "effnet_percentile", "heard_percentile"]].sort_values(["platform", "effnet_percentile"])

,platform,file,effnet_percentile,heard_percentile
0,spotify_tests,Y2Mate.is - ELWD - U MAKE ME OFFICIAL VIDEO.mp3,0.001499,0.009258
5,spotify_tests,Y2Mate.is - Soul.mp3,0.002499,0.002627
2,spotify_tests,Y2Mate.is - Loure - In The Evenings.mp3,0.002999,0.347929
3,spotify_tests,Y2Mate.is - Melodiesinfonie - Peace On Earth.mp3,0.002999,0.002627
7,spotify_tests,Y2Mate.is - gabriel Two Scents - Beauty In Imperfection.mp3,0.002999,0.003878
1,spotify_tests,Y2Mate.is - Lola.mp3,0.003498,0.007256
4,spotify_tests,Y2Mate.is - Naima Blue.mp3,0.003498,0.029151
8,spotify_tests,Y2Mate.is - la danse.mp3,0.005497,0.150256
6,spotify_tests,Y2Mate.is - Tour Maubourg - Ode To Love Official Video.mp3,0.007496,0.227074
11,youtube_tests,Y2Mate.is - Careless Tiny Room Sessions.mp3,0.000500,0.004504


In [9]:
print("mean percentile by platform:")
print(compare.groupby("platform")[["effnet_percentile", "heard_percentile"]].mean())

mean percentile by platform:
               effnet_percentile  heard_percentile
platform                                          
spotify_tests           0.003665          0.086673
youtube_tests           0.002166          0.051059


**This is the headline number of the whole notebook.** heard space put
Spotify's picks at the 8.7th percentile of the catalogue and YouTube's at the
5.1st, after three different catalogue sizes all landed in that same range.
EffNet puts them at the **0.37th and 0.22nd percentile** — over 20x closer, on
the exact same 18 tracks and the exact same seed. Three months of catalogue
engineering (medium, genre-balancing) moved this number by a rounding error;
switching the embedding moved it by more than an order of magnitude. That's
about as clean a signal as this project has produced for where the real
bottleneck was: not the catalogue, the hand-built features.

**Listen:** the seed, EffNet's own top-10 for it.

In [10]:
play(SEED_PATH, "SEED — Elyjah Slaps the Space")

sims_to_sample = Eu @ seed_vec_u
order = np.argsort(-sims_to_sample)[:10]
for j in order:
    tid = int(ids[j])
    mm = meta.loc[tid]
    play(fma_audio_path(tid), f"distance={1 - sims_to_sample[j]:.3f}  {mm.artist} — {mm.title}  [{mm.genre_top}]")

SEED — Elyjah Slaps the Space


distance=0.205  Comfort Fit — Sorry  [Hip-Hop]


distance=0.205  Garmisch — You Come Get Your Boy Now  [Pop]


distance=0.218  Josh Spacek — Loaded  [Instrumental]


distance=0.220  6th Sense — 4AM Instrumental     {Wildabeast}  [Hip-Hop]


...

distance=0.259  Deltason — Tunnel Vision  [Electronic]


distance=0.269  Amitron_7 — Escape Under Cover of Night  [Electronic]


distance=0.274  The Honorable Sleaze — Love Me/Hate Me (Instrumental)  [Hip-Hop]


distance=0.281  BOPD — 1.26 beat1  [Hip-Hop]


distance=0.286  Deltason — Back To Earth  [Electronic]


## 5. The real numbers: full catalogue, not a 2,001-track sample

Everything above ran against the ~250/genre sample this notebook started
with, since that's what was embedded first. The full 7,994-track catalogue
was extracted afterward (`data/effnet_embeddings_full.npz`, via the same
standalone script) and `modeling/effnet_recommender.py` — a proper
`TrackRecommender`-shaped class for these embeddings, `similar_to` / `adventure`
dial and all — is what actually queries it here, rather than the ad-hoc numpy
this notebook used for the sample. Re-running the two checks that matter most
at full scale, both to get real numbers and to dogfood the new class.

In [11]:
from modeling.data import load_fma
from modeling.effnet_recommender import EffNetRecommender

tracks_baseline = load_fma("small")[1]
full_rec = EffNetRecommender.from_npz(REPO_ROOT / "data" / "effnet_embeddings_full.npz", tracks_baseline)
print(f"full catalogue: {len(full_rec.track_ids_)} tracks")

full_labels = tracks_baseline.loc[full_rec.track_ids_][("track", "genre_top")]
full_rng = np.random.default_rng(1)
full_rows = []
for genre in sorted(full_labels.dropna().unique()):
    pool = np.intersect1d(full_labels.index[full_labels == genre].to_numpy(), full_rec.track_ids_)
    sample = full_rng.choice(pool, size=min(50, len(pool)), replace=False)
    for seed_id in sample:
        recs = full_rec.similar_to(int(seed_id), n=10)
        full_rows.append({"genre": genre, "agreement@10": (recs["genre"] == genre).mean()})

full_summary = pd.DataFrame(full_rows).groupby("genre")["agreement@10"].mean().round(3).sort_values()
full_summary

full catalogue: 7994 tracks


genre
Pop              0.316
Experimental     0.422
Instrumental     0.518
Electronic       0.656
Folk             0.656
International    0.680
Rock             0.722
Hip-Hop          0.772
Name: agreement@10, dtype: float64

In [12]:
full_E = full_rec.embedding_.to_numpy()
full_Eu = full_E / np.linalg.norm(full_E, axis=1, keepdims=True)
full_catalog_dist = np.sort(1 - (full_Eu @ seed_vec_u))
full_catalog_size = len(full_catalog_dist)

full_rows2 = []
for i, (name, platform) in enumerate(zip(ext_names, ext_platforms)):
    if platform == "seed":
        continue
    d = float(1 - ext_vecs_u[i] @ seed_vec_u)
    rank = int(np.searchsorted(full_catalog_dist, d)) + 1
    full_rows2.append({"platform": platform, "file": str(name), "full_percentile": rank / full_catalog_size})

full_scored = pd.DataFrame(full_rows2)
print("mean percentile, full 7,994-track catalogue:")
print(full_scored.groupby("platform")["full_percentile"].mean())
print()
print("(for comparison, the 2,001-track sample gave spotify=0.37%, youtube=0.22% -- "
      "the full catalogue is not just consistent with that, it's noticeably more extreme)")

mean percentile, full 7,994-track catalogue:
platform
spotify_tests    0.001654
youtube_tests    0.001126
Name: full_percentile, dtype: float64

(for comparison, the 2,001-track sample gave spotify=0.37%, youtube=0.22% -- the full catalogue is not just consistent with that, it's noticeably more extreme)


Several YouTube recommendations land at **rank 1 of 7,994** — closer to the
seed than every single track already in the catalogue. Worth hearing, not
just reading as a number.

In [13]:
play(SEED_PATH, "SEED — Elyjah Slaps the Space")
rank1 = full_scored.sort_values("full_percentile").head(5)
for row in rank1.itertuples():
    path = REPO_ROOT / "data" / "raw" / row.platform / row.file
    play(path, f"[{row.platform}] percentile={row.full_percentile:.4%}  {row.file}")

SEED — Elyjah Slaps the Space


[youtube_tests] percentile=0.0125%  Y2Mate.is - zeste.mp3


[youtube_tests] percentile=0.0125%  Y2Mate.is - _You hate Jazz__.mp3


[youtube_tests] percentile=0.0125%  Y2Mate.is - Gumbo.mp3


[youtube_tests] percentile=0.0125%  Y2Mate.is - Careless Tiny Room Sessions.mp3


[youtube_tests] percentile=0.0125%  Y2Mate.is - nyc in 1940.mp3


## 6. Familiar / Bridge / Adventurous, same method as notebook 07 — now on EffNet

Same `genres_all`-based tier split notebook 07 ran on heard space, same three
seeds (Hip-Hop / Instrumental / Pop), plus the external seed with a genre
inferred from its own nearest neighbours (no ground truth for a track outside
FMA). `EffNetRecommender` matches `TrackRecommender`'s interface closely
enough that the tier logic barely changes — `rec` is just `full_rec` here.

In [14]:
import ast

genres_all = tracks_baseline[("track", "genres_all")].apply(ast.literal_eval)
genres_lookup = pd.read_csv(REPO_ROOT / "data" / "raw" / "fma_metadata" / "genres.csv", index_col=0)["title"]


def genre_names(gids):
    return [genres_lookup.get(i, str(i)) for i in gids]


def tiers_for(rec, seed_id=None, seed_vec=None, seed_genres=None, seed_artist=None,
              n_familiar=5, n_bridge=5, n_adventurous=5, bridge_window=150, adventure=0.85):
    # Familiar/Bridge/Adventurous for either a catalogue seed (seed_id) or an
    # external one (seed_vec, already in rec's space; seed_genres supplied
    # explicitly since an external track has no genres_all of its own)
    if seed_vec is None:
        row = rec._position(seed_id)
        seed_vec = rec.embedding_.iloc[[row]]
    distances, idx = rec.index_.kneighbors(seed_vec, n_neighbors=600)
    distances, idx = distances[0], idx[0]
    if seed_id is not None:
        distances, idx = distances[1:], idx[1:]
    candidate_ids = rec.track_ids_[idx]

    if seed_artist is not None:
        artists = tracks_baseline.loc[candidate_ids, ("artist", "name")].to_numpy()
        keep = artists != seed_artist
        candidate_ids, distances = candidate_ids[keep], distances[keep]

    if seed_genres is None:
        seed_genres = set(genres_all.get(seed_id, []))
    overlaps = np.array([bool(seed_genres & set(genres_all.get(c, []))) for c in candidate_ids])

    familiar = [(candidate_ids[i], distances[i]) for i in range(len(candidate_ids)) if overlaps[i]][:n_familiar]
    bridge_pool = [(candidate_ids[i], distances[i])
                    for i in range(min(bridge_window, len(candidate_ids))) if not overlaps[i]]
    bridge = bridge_pool[:n_bridge]

    start = depth_for(adventure, max_depth=500)
    adventurous = [(candidate_ids[i], distances[i])
                   for i in range(start, min(start + n_adventurous, len(candidate_ids)))]
    return familiar, bridge, adventurous


def show(label, items):
    print(f"  {label}:")
    for tid, d in items:
        m = tracks_baseline.loc[tid]
        g = genre_names(genres_all.get(tid, []))
        print(f"    {d:.3f}  {m[('artist','name')]} — {m[('track','title')]}  "
              f"[{m[('track','genre_top')]}] genres_all={g}")

In [15]:
from modeling.recommender import depth_for

TIER_SEEDS = [2, 40659, 3538]  # AWOL - Food (Hip-Hop); Albert Glasser (Instrumental); Cryptacize (Pop)

for seed_id in TIER_SEEDS:
    m = tracks_baseline.loc[seed_id]
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  "
          f"[{m[('track','genre_top')]}]  genres_all={genre_names(genres_all.get(seed_id, []))} ===")
    fam, bri, adv = tiers_for(full_rec, seed_id=seed_id, seed_artist=m[("artist", "name")])
    show("Familiar", fam)
    show("Bridge", bri)
    show("Adventurous", adv)


=== SEED 2  AWOL — Food  [Hip-Hop]  genres_all=['Hip-Hop'] ===
  Familiar:
    0.145  Sun Sunych — 43-13  [Hip-Hop] genres_all=['Rap', 'Hip-Hop']
    0.152  The Honorable Sleaze — Fist City  [Hip-Hop] genres_all=['Hip-Hop']
    0.171  Hi-Rez — Race With Time (Prod. Joel Johnston)  [Hip-Hop] genres_all=['Rap', 'Hip-Hop']
    0.173  Hi-Rez — The Remedy (Prod. Joel Johnston)  [Hip-Hop] genres_all=['Rap', 'Hip-Hop']
    0.180  CM & Tha Silent Partner — What's It All For  [Hip-Hop] genres_all=['Hip-Hop']
  Bridge:
    0.282  This One — No Time For Lookin' Back  [Electronic] genres_all=['Electronic']
  Adventurous:
    0.302  Digi G'Alessio — darix togni  [Electronic] genres_all=['Dance', 'Electronic', 'Chill-out', 'Bigbeat', 'Techno', 'House', 'Trip-Hop']
    0.302  Cockmasta Flex — Sodomy Dungeon (remastered)  [Hip-Hop] genres_all=['Rap', 'Hip-Hop']
    0.303  Stray — Cascos  [Hip-Hop] genres_all=['Nerdcore', 'Alternative Hip-Hop', 'Hip-Hop']
    0.303  Tha Silent Partner — Mandingo Ocean

**Listen:** all three seeds, all three tiers, EffNet space.

In [16]:
for seed_id in TIER_SEEDS:
    m = tracks_baseline.loc[seed_id]
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]} ===")
    play(fma_audio_path(seed_id), "SEED")
    fam, bri, adv = tiers_for(full_rec, seed_id=seed_id, seed_artist=m[("artist", "name")])
    for label, items in [("Familiar", fam), ("Bridge", bri), ("Adventurous", adv)]:
        for tid, d in items:
            mm = tracks_baseline.loc[tid]
            play(fma_audio_path(tid),
                 f"{label}  distance={d:.3f}  {mm[('artist','name')]} — {mm[('track','title')]}  [{mm[('track','genre_top')]}]")


=== SEED 2  AWOL — Food ===
SEED


Familiar  distance=0.145  Sun Sunych — 43-13  [Hip-Hop]


Familiar  distance=0.152  The Honorable Sleaze — Fist City  [Hip-Hop]


Familiar  distance=0.171  Hi-Rez — Race With Time (Prod. Joel Johnston)  [Hip-Hop]


Familiar  distance=0.173  Hi-Rez — The Remedy (Prod. Joel Johnston)  [Hip-Hop]


...

Adventurous  distance=0.286  Ben von Wildenhaus — Week Two  [Folk]


Adventurous  distance=0.287  MV + EE — The Hungry Stones  [Folk]


Adventurous  distance=0.287  Big Blood — I've Been A Baby All My Life (I Hope You Don't Expect A Man)  [Folk]


Adventurous  distance=0.287  Liger — Oh, Chicken Feathers!  [Pop]


Adventurous  distance=0.287  Itasca — Henfight  [Folk]


### The external seed — genre inferred the same way as notebook 07

In [17]:
seed_vec_2d = seed_vec_u.reshape(1, -1)
d0, idx0 = full_rec.index_.kneighbors(seed_vec_2d, n_neighbors=5)
neighbor_ids = full_rec.track_ids_[idx0[0]]
inferred_genres = set().union(*[set(genres_all.get(t, [])) for t in neighbor_ids])
print("inferred genre (union of top-5 neighbours' genres_all):", genre_names(inferred_genres))

ext_fam, ext_bri, ext_adv = tiers_for(full_rec, seed_vec=seed_vec_2d, seed_genres=inferred_genres)
print("\n=== SEED — Elyjah Slaps the Space (external, EffNet space) ===")
show("Familiar", ext_fam)
show("Bridge", ext_bri)
show("Adventurous", ext_adv)

inferred genre (union of top-5 neighbours' genres_all): ['Soundtrack', 'Instrumental', 'Hip-Hop', 'Pop', 'Experimental Pop', 'Synth Pop']

=== SEED — Elyjah Slaps the Space (external, EffNet space) ===
  Familiar:
    0.205  Comfort Fit — Sorry  [Hip-Hop] genres_all=['Hip-Hop']
    0.205  Garmisch — You Come Get Your Boy Now  [Pop] genres_all=['Pop', 'Synth Pop']
    0.211  Jiony — Waiting For The Sun  [Pop] genres_all=['Pop', 'Experimental Pop']
    0.218  Josh Spacek — Loaded  [Instrumental] genres_all=['Soundtrack', 'Instrumental']
    0.218  Malaventura — Let's the kids play  [Pop] genres_all=['Pop', 'Experimental Pop']
  Bridge:
    0.259  Deltason — Tunnel Vision  [Electronic] genres_all=['Ambient Electronic', 'Downtempo', 'Electronic']
    0.269  Amitron_7 — Escape Under Cover of Night  [Electronic] genres_all=['Chill-out', 'Ambient Electronic', 'House', 'Electronic']
    0.272  Jason Shaw — Fat Caps  [Electronic] genres_all=['Techno', 'Electronic']
    0.277  Deltason — Flow Of

**Listen:** the seed, all three tiers, EffNet space.

In [ ]:
    lpplay(SEED_PATH, "SEED — Elyjah Slaps the Space")
for label, items in [("Familiar", ext_fam), ("Bridge", ext_bri), ("Adventurous", ext_adv)]:
    for tid, d in items:
        mm = tracks_baseline.loc[tid]
        play(fma_audio_path(tid),
             f"{label}  distance={d:.3f}  {mm[('artist','name')]} — {mm[('track','title')]}  [{mm[('track','genre_top')]}]")

SEED — Elyjah Slaps the Space


Familiar  distance=0.205  Comfort Fit — Sorry  [Hip-Hop]


Familiar  distance=0.205  Garmisch — You Come Get Your Boy Now  [Pop]


Familiar  distance=0.211  Jiony — Waiting For The Sun  [Pop]


Familiar  distance=0.218  Josh Spacek — Loaded  [Instrumental]


...

Adventurous  distance=0.388  harmonic defiance — the endless corner  [Electronic]


Adventurous  distance=0.388  Blue Dot Sessions — Liquor Files - Hickory  [Instrumental]


Adventurous  distance=0.388  Jules — Keep it Real  [Hip-Hop]


Adventurous  distance=0.388  harmonic defiance — everything is love  [Electronic]


Adventurous  distance=0.389  Digi G'Alessio — darix togni  [Electronic]


## Summary, and positioning for the final presentation

**What EffNet changed** (full 7,994-track catalogue numbers, not the sample):

| check | heard space | Discogs-EffNet |
|---|---:|---:|
| Hip-Hop agreement@10 | 0.49 | **0.77** |
| Pop agreement@10 | 0.24 | **0.32** |
| external seed, Spotify percentile | 8.67% | **0.17%** |
| external seed, YouTube percentile | 5.11% | **0.11%** |

The 2,001-track sample earlier in this notebook *understated* the effect on
both checks — a smaller sample means fewer close same-genre candidates to
compete with, and a smaller catalogue to rank the external seed against. Five
of YouTube's nine recommendations land at rank 1 of 7,994 — closer to the seed
than every track already in the catalogue.

Two things are true at once, and both matter. EffNet is a dramatically better
foundation for the external-seed comparison that motivated this whole
diagnosis — over 45x closer to what Spotify and YouTube actually recommended,
after catalogue engineering alone (small -> medium -> balanced) never moved
that number by more than half a percentage point. And EffNet independently
reproduces Pop's relative weakness, on a *completely different* model trained
on a *completely different objective* (Discogs style classification, not FMA
audio-feature regression) — which is strong evidence that finding is a real
property of these FMA "Pop" tags, not an artifact of our own feature choices.

**For the presentation:** cosine.club answers "what sounds like this" — pure
similarity, no exploration control; its own FAQ says a high score means
"these sound alike," not "either one is good." TasteBridge answers "how far
from this do I want to go." The depth test above says that dial has a real
foundation to stand on in this embedding: genre agreement decays gradually
(0.53 -> 0.38 -> 0.22 from rank 10 to 300), not as a cliff, so there's a
genuine Bridge-shaped middle zone between "obviously the same genre" and
"just somewhere else" — matching what was described as wanting Bridge to
carry "a nice link" rather than being a random jump.